# Tutorial: how to use `pangeo-fish`


**Overview.**

This Jupyter notebook demonstrates how to use `pangeo-fish`.

Specifically, we will fit the geolocation on the data from the study conducted by M. Gonze et al. titled "Combining acoustic telemetry with archival tagging to investigate the spatial dynamics of the understudied pollack *Pollachius pollachius*", accepted for publication in the Journal of Fish Biology.

We will use the biologging tag "A19124", which was attached to pollock fish.

As for the reference Earth Observation (EO) data, we consider the European Union Copernicus Marine Service Information (CMEMS) product "NORTHWESTSHELF_ANALYSIS_FORECAST_PHY_004_013".

_NB: In addition to the Data Storage Tag (DST), the biologging data includes **teledetection by acoustic signals**, as well as the release and recapture/death information of the fish._

Both the reference EO and the biologging data are publicly available, and the computations should be tractable for most standard laptops.

**Workflow.**

Let's first summarize the key steps for running the geolocation:

1. **Define the configuration:** define the required parameters for the analysis.
2. **Compare the reference data with the DST information:** compare the data from the reference model with the biologging data. 
3. **Regrid the comparison to HEALPix:** translate the comparison into a HEALPix grid to avoid spatial distortion.
4. **Construct the temporal emission matrix:** create a temporal emission probability distribution (_pdf_) from the transformed grid.
5. **Construct another emission matrix with the acoustic detections:** calculate a similar model to the previous one, using this time the acoustic teledetections.
6. **Combine and normalize the matrices:** merge and normalize the two _pdfs_.
7. **Estimate (or _fit_) the geolocation model:** determine the parameters of the model based on the normalized emission matrix.
8. **Compute the state probabilities and generate trajectories:** compute the fish's location probability distribution and generate subsequent trajectories.
9. **Visualization:** visualize the evolution of the spatial probabilities over time and export the video.

Throughout this tutorial, you will gain practical experience in setting up and executing a typical workflow using `pangeo-fish` such that you can then apply the tool with your use-case study.

## 1. Initialization and configuration definition

In this step, we prepare the execution of the analysis.
It includes:
- Installing the necessary packages.
- Importing the required libraries.
- Defining the parameters for the next stages of the workflow.
- Configuring the cluster for distributed computing.
    

Only if you don't have good GPU (>=7.5)

In [1]:
# do this
import torch
import os

os.environ["CUDA_VISIBLE_DEVICES"] = ""

### Mandatory libraries

In [2]:
from pint_xarray import unit_registry as ureg
import hvplot.xarray
import xarray as xr
import sys

# sys.path.append("../")
import pangeo_fish
from pangeo_fish.xarray_update import Accessor
from pangeo_fish.helpers import multiplot_healpix, multi_map_with_synced_sliders

/home/cchauveau/micromamba/envs/pangeo-fish-pr262/lib/python3.11/site-packages/movingpandas/__init__.py:41: UserWarning: Missing optional dependencies. To use the trajectory smoother classes please install Stone Soup (see https://stonesoup.readthedocs.io/en/latest/#installation).
  warnings.warn(e.msg, UserWarning)


### Parameters

In [3]:
# tag_name corresponds to the name of the biologging tag name (DST identification number),
# which is also a path for storing all the information for the specific fish tagged with tag_name.

tag_name = "A19226"#"A18828"  # "A19124"

# tag_root specifies the root URL for tag data used for this computation. You can check the present link to see other tags.
# You can also put a local path if you have a tag on your computer

tag_root = "https://data-taos.ifremer.fr/demo/tag/tag/"

copernicus_model_name = "cmems_mod_glo_phy_my_0.083deg_P1D-m"

# ref_url is the path to the reference model.
# When set to None, load_model fetches the CMEMS Global Ocean Physics
# Reanalysis (daily-mean, 1/12 deg, `cmems_mod_glo_phy_my_0.083deg_P1D-m`)
# directly via the copernicusmarine client.
# To use a different reference, pass a `.yaml` intake catalog or a
# `.parq` / `.json` kerchunk reference here.
ref_url = None

# scratch_root specifies the root directory for storing output files.
# storage_options specifies options for the filesystem storing output files.

## example for remote storage (you need gfts credentials for this one)
scratch_root = "s3://destine-gfts-data-lake/demo"
storage_options = {
    "anon": False,
    "profile": "gfts",
    "client_kwargs": {
        "endpoint_url": "https://s3.gra.perf.cloud.ovh.net",
        "region_name": "gra",
    },
}
## example for using your local file system instead
scratch_root = "./local_storage"
storage_options = None

# Default chunk value for time dimension. This values depends on the configuration of your dask cluster.
chunk_time = 1  # 1 means that a chunk will contain one timestep. -1 will take all the time step in one chunk

# Either to use a HEALPix grid (["cells"]) or a 2D grid (["x", "y"])
dims = ["cells"]

# bbox, bounding box, defines the latitude and longitude range for the analysis area.
bbox = {"latitude": [46, 59], "longitude": [-14, 2]}
# relative_depth_threshold defines the acceptable fish depth relative to the maximum tag depth.
# It determines whether the fish can be considered to be in a certain location based on depth.
# If you are not using a bathy pdf (calculate later at choice) put 0.8 (hand made)
# it has to be between 0 and 1
relative_depth_threshold = 0

# refinement level  defines the resolution of the healpix grid used for regridding.
refinement_level = 10  # correspond to 12*2**10 cells

# min_vertices sets the minimum number of vertices for a valid transcription for regridding. It is for the use of
min_vertices = 1

# differences_std sets the standard deviation for scipy.stats.norm.pdf.
# It expresses the estimated certainty of the field of difference.
differences_std = 0.75  # in °C
# initial_std sets the covariance for initial event.
# It shows the certainty of the initial area.
initial_std = 1e-5  # hand made in radians
# recapture_std sets the covariance for recapture event.
# It shows the certainty of the final recapture area if it is known.
recapture_std = 1e-4
# earth_radius defines the radius of the Earth used for distance calculations.
earth_radius = ureg.Quantity(6371, "km")
# maximum_speed sets the maximum allowable speed for the tagged fish.
maximum_speed = ureg.Quantity(60, "km / day")
# adjustment_factor adjusts parameters for a more fuzzy search.
# It will factor the allowed maximum displacement of the fish.
adjustment_factor = 5
# truncate sets the truncating factor for computed maximum allowed sigma for convolution process.
truncate = 4

# receiver_buffer sets the maximum allowed detection distance for acoustic receivers.
receiver_buffer = ureg.Quantity(1000, "m")


# tolerance describes the tolerance level of the search during the fitting/optimization of the geolocation.
# Smaller values will make the optimization iterate more
tolerance = 1e-6

# track_modes defines the modes for generating fish's trajectories.
track_modes = ["mean", "mode"]
# additional_track_quantities sets quantities to compute for tracks using moving pandas.
additional_track_quantities = ["speed", "distance"]


# time_step defines the time interval between each frame of the visualization
time_step = 3
# ellipsoid defines which model of the earth will be used: "sphere" is a sphere,
# "WGS84" is a ellipsoidal model with the parameter of the earth
ellipsoid = "sphere"

In [4]:
# Define target root directories for storing analysis results.
target_root = f"{scratch_root}/{tag_name}"

# Defines default chunk size for optimization.
default_chunk = {"time": chunk_time, "lat": -1, "lon": -1}
default_chunk_dims = {"time": chunk_time}
default_chunk_dims.update({d: -1 for d in dims})

### Dask
allows parallelisation and so faster calculs

In [5]:
# Set up a local cluster for distributed computing.
from distributed import LocalCluster

cluster = LocalCluster()
client = cluster.get_client()
client

Connection method: Cluster object,Cluster type: distributed.LocalCluster
Dashboard: http://127.0.0.1:8787/status,
Dashboard: http://127.0.0.1:8787/status,Workers: 4
Total threads: 16,Total memory: 24.75 GiB
Status: running,Using processes: True
Comm: tcp://127.0.0.1:34515,Workers: 0
Dashboard: http://127.0.0.1:8787/status,Total threads: 0
Started: Just now,Total memory: 0 B
Comm: tcp://127.0.0.1:43847,Total threads: 4
Dashboard: http://127.0.0.1:37811/status,Memory: 6.19 GiB
Nanny: tcp://127.0.0.1:42099,


### Opening the biologging data
Now that everything is set up, we can start by loading the biologging data (or _tag_)

In [6]:
from pangeo_fish.helpers import load_tag

tag, tag_log, time_slice = load_tag(
    tag_root=tag_root, tag_name=tag_name, storage_options=storage_options
)
tag

<xarray.DataTree>
Group: /
│   Attributes:
│       pit_tag_id:       A19226
│       acoustic_tag_id:  OPI-612
│       scientific_name:  Pollachius pollachius
│       common_name:      Pollock
│       project:          FISHINTEL
│       tag_name:         A19226
├── Group: /dst
│       Dimensions:      (time: 482292)
│       Coordinates:
│         * time         (time) datetime64[ns] 4MB 2022-05-18T22:00:00 ... 2023-10-03...
│       Data variables:
│           temperature  (time) float64 4MB 18.39 18.39 18.36 ... 19.67 19.75 19.95
│           pressure     (time) float64 4MB 2.93 2.93 2.87 2.87 ... 4.31 4.31 4.37 4.31
├── Group: /tagging_events
│       Dimensions:     (event_name: 2)
│       Coordinates:
│         * event_name  (event_name) object 16B 'release' 'fish_death'
│       Data variables:
│           time        (event_name) datetime64[ns] 16B 2022-05-19T17:21:00 2023-08-0...
│           longitude   (event_name) float64 16B -3.459 -3.586
│           latitude    (event_name) float64 16B 48.88 48.8
└── Group: /stations
        Dimensions:            (deployment_id: 41)
        Coordinates:
          * deployment_id      (deployment_id) int64 328B 28689 28690 ... 29666 59010
        Data variables:
            station_name       (deployment_id) object 328B 'ancrage_mahuda' ... 'stiff'
            deploy_time        (deployment_id) datetime64[ns] 328B 2022-06-13T06:14:0...
            deploy_longitude   (deployment_id) float64 328B -5.103 -5.112 ... -5.025
            deploy_latitude    (deployment_id) float64 328B 48.45 48.45 ... 48.47 48.47
            recover_time       (deployment_id) datetime64[ns] 328B 2022-06-20T14:07:0...
            recover_longitude  (deployment_id) float64 328B nan nan nan ... nan nan nan
            recover_latitude   (deployment_id) float64 328B nan nan nan ... nan nan nan

You can plot the time series of the DST with the function `plot_tag()`:

In [7]:
from pangeo_fish.helpers import plot_tag

plot = plot_tag(
    tag=tag,
    tag_log=tag_log,
    # you can directly save the plot if you want
    save_html=True,
    storage_options=storage_options,
    target_root=target_root,
)
plot

:Overlay
   .Curve.I    :Curve   [time]   (pressure)
   .Scatter.I  :Scatter   [time]   (pressure)
   .Curve.II   :Curve   [time]   (temperature)
   .Scatter.II :Scatter   [time]   (temperature)

The red points are the one used in the following steps. It is the asumed time when the tag was on a living fish.

### Credentials for reference model
The cells below allow you to create a file where your credentials for copernicus will be stocked (avoid the pain to enter them each time you run the cell). It allows you to commit this notebook without having to remove any part.

If you open the notebook for the first time unraw the following cell and execute it
from getpass import getpass

The next cell allows to read your credential in a text file and use them


In [8]:
credentials = {}
with open("copernicus_credentials.txt") as f:
    for line in f:
        line = line.strip()
        if line and "=" in line:
            key, value = line.split("=", 1)
            credentials[key.strip()] = value.strip()

Username = credentials["username"]
Password = credentials["password"]

## 2. Compare the reference data with the DST logs (using copernicus)

### Open the reference data model

In [ ]:
from pangeo_fish.helpers import load_model, compute_diff

reference_model = load_model(
    uri=ref_url,
    tag_log=tag_log,
    time_slice=time_slice,
    bbox=(bbox | {"max_depth": tag_log["pressure"].max()}),
    chunk_time=chunk_time,
    remote_options={},
    copernicus_model_name=copernicus_model_name,
    Username=Username,
    Password=Password,
)

### Compute the difference

In [ ]:
%%time
diff = compute_diff(
    reference_model=reference_model,
    tag_log=tag_log,
    relative_depth_threshold=relative_depth_threshold,
    chunk_time=chunk_time,
)[0]
diff = diff.compute()
diff

The next plot should figure a line. It will means that every calcul were made

In [ ]:
%%time
diff["diff"].count(["lat", "lon"]).plot()

In [ ]:
%%time
diff.to_zarr(
    f"{target_root}/diff.zarr", mode="w", storage_options=storage_options, zarr_format=2
)

## 3. HEALPix regridding

In this step, we regrid the data from above to HEALPix coordinates. HEALPix (Hierarchical Equal Area isoLatitude Pixelization) is a spherical pixelation scheme that divides the sphere into equal-area pixels, eliminating spatial distortion [see the HEALPix documentation](https://healpix.sourceforge.io/).

This is a complex process, composed of several steps such as defining the HEALPix grid, creating the target grid and computing interpolation weights

Fortunately though, `pangeo-fish` embarks high-level functions to do the work for us!

In [ ]:
from pangeo_fish.helpers import (
    open_diff_dataset,
    regrid_dataset_hpresample,
)

In [ ]:
# Open the previous dataset (only necessary if you resume the notebook from here)
diff = open_diff_dataset(target_root=target_root, storage_options=storage_options)
diff

In [ ]:
reshaped, resampling_info = regrid_dataset_hpresample(
    ds=diff, refinement_level=refinement_level, min_vertices=min_vertices, dims=dims
)
reshaped

In [ ]:
resampling_info["bbox"] = bbox
import json

# à enregistrer sous target root, doit contenir refinement level (non déjà sur combined), bbox, résolution de départ (xi,yi), ellipsoid
with open(f"{target_root}/resampling_info.json", "w") as f:
    json.dump(resampling_info, f)

with open(f"{target_root}/resampling_info.json") as f:
    resampling_info = json.load(f)
resampling_info

Let's plot the same chart as before to check that the HEALPix regridding hasn't changed the data

In [ ]:
reshaped["diff"].count(dims).plot()

In [ ]:
# Saves the result
reshaped.chunk(default_chunk_dims).to_zarr(
    f"{target_root}/diff-regridded.zarr",
    mode="w",
    consolidated=True,
    compute=True,
    storage_options=storage_options,
    zarr_format=2,
)

If you want to see the diff, you may have to install ipleaflet and ipwidget and some other extensions (they don't have compatibility problem and will be asked)

In [ ]:
reshaped.healpix.plot(
    var="diff", refinement_level=refinement_level, alpha=0.8, ellipsoid=ellipsoid
)

## 4. Compute the emission probability distribution

In this step, we use the comparison result from the step above to construct the emission probability matrix.

This comparison is essentially he differences between the temperature measured by the tag and the reference sea temperature. 

The emission probability matrix represents the likelihood of observing a specific temperature difference given the model parameters and configurations.

In [ ]:
from pangeo_fish.helpers import compute_emission_pdf

In [ ]:
# Open the previous dataset (only necessary if you resume the notebook from here)
differences = xr.open_dataset(
    f"{target_root}/diff-regridded.zarr",
    engine="zarr",
    chunks={},
    storage_options=storage_options,
)

# ... and compute the emission matrices
emission_pdf = compute_emission_pdf(
    diff_ds=differences,
    events_ds=tag["tagging_events"].ds,
    differences_std=differences_std,
    initial_std=initial_std,
    recapture_std=recapture_std,
    dims=dims,
    chunk_time=chunk_time,
)[0]
emission_pdf

If you want to see the pdf

In [ ]:
emission_pdf.healpix.plot("pdf", refinement_level, ellipsoid=ellipsoid)

Whatever the temporal distribution looks like, they must **never** (i.e, at _any time step_) sum to 0.

How could we check that visually? You'd have guessed it by now: similarly as before!

In [ ]:
emission_pdf = emission_pdf.chunk(default_chunk_dims).persist()
emission_pdf["pdf"].count(dims).plot()

In [ ]:
# Save the dataset
emission_pdf.to_zarr(
    f"{target_root}/emission_diff.zarr",
    mode="w",
    consolidated=True,
    storage_options=storage_options,
    zarr_format=2,
)

In [ ]:
emission_pdf.attrs["sources"] = emission_pdf.attrs.get("sources", []) + [
    "temperature"
]  # this line allows to keep in memory what pdf had been calculated so far
emission_pdf.to_zarr(
    f"{target_root}/total_pdf.zarr",
    mode="w",
    consolidated=True,
    storage_options=storage_options,
    zarr_format=2,
)

## 5. Compute a 2nd _pdf_ with the acoustic detections

In this step, the goal is to calculate another emission distribution, this time from the acoustic detections.
**As such, it requires the tag to include at least one detection.**

These additional probabilities will enhance the emission _pdf_ constructed in the previous step by incorporating information from acoustic telemetry.

_NB: we will merge and normalize the two pdfs in the next stage of the workflow._

In [ ]:
from pangeo_fish.helpers import compute_acoustic_pdf

In [ ]:
# Load the previous emission pdf and compute the emission probabilities based on acoustic detections
emission_diff = xr.open_dataset(
    f"{target_root}/emission_diff.zarr",
    engine="zarr",
    chunks={},
    storage_options=storage_options,
)
acoustic_pdf = compute_acoustic_pdf(
    emission_ds=emission_diff,
    tag=tag,
    receiver_buffer=receiver_buffer,
    chunk_time=chunk_time,
    dims=dims,
)[0]
acoustic_pdf = acoustic_pdf.persist()
acoustic_pdf

If you wonder how this emission matrix looks like, you can plot a combined plot of the detections and the probabilities:

In [ ]:
tag["acoustic"]["deployment_id"].hvplot.scatter(c="red", marker="x") * (
    acoustic_pdf["acoustic"] != 0
).sum(dim=dims).hvplot()

### Explanations
On the plot above, at detection times the number of counted values drop to a few value (`5` in this example).

These numbers correspond to the number of pixels that covers the detection area.

Therefore, such drop is expected, since at those times we know that the fish was detected around the acoustic receivers, and so it **can't** be elsewhere.

These sporadic detections will constraint a lot the geolocation model upon optimizing!

**The next cell is optional. It will save the acoustic emission distribution. It is not necessary (see the next step).**

In [ ]:
acoustic_pdf.to_zarr(
    f"{target_root}/acoustic.zarr",
    mode="w",
    consolidated=True,
    storage_options=storage_options,
)

#### Merging

In [ ]:
## ouvrir le total actuel
current_total = xr.open_dataset(
    f"{target_root}/total_pdf.zarr",
    engine="zarr",
    chunks={},
    storage_options=storage_options,
)
current_total

In [ ]:
if "acoustic" in current_total.data_vars:
    pass
else:
    current_total = current_total.load()
    current_total.attrs["sources"] = current_total.attrs.get("sources", []) + [
        "acoustic"
    ]

    merged_pdf = current_total.merge(
        acoustic_pdf.drop_indexes(["cell_ids"]), compat="override"
    )

    merged_pdf.to_zarr(
        f"{target_root}/total_pdf.zarr",
        mode="w",
        consolidated=True,
        storage_options=storage_options,
        zarr_format=2,
    )
merged_pdf

## 5.2. Compute a 3rd pdf with bathy

In this step, the goal is to calculate another emission distribution, this time using a bathymetry like GEBCO, EMODNET...

These additional probabilities will enhance the emission pdf constructed in the previous step by incorporating information from bathymetry information.

/!\ you must have run and save at least once chapter 2

In [ ]:
if "reference_model" in locals():
    pass
else:
    from pangeo_fish.helpers import load_model

    reference_model = load_model(
        uri=ref_url,
        tag_log=tag_log,
        time_slice=time_slice,
        bbox=(bbox | {"max_depth": tag_log["pressure"].max()}),
        chunk_time=chunk_time,
        remote_options={},
        Username=Username,
        Password=Password,
    )

In [ ]:
emission_diff = xr.open_dataset(
    f"{target_root}/emission_diff.zarr",
    engine="zarr",
    chunks={},
    storage_options=storage_options,
)
emission_diff

In [ ]:
import fsspec
import numpy as np
from pangeo_fish.cf import bounds_to_bins
from pangeo_fish.tags import adapt_model_time, reshape_by_bins, to_time_slice
from pangeo_fish.bathy import batch_compute_pdf_bathy
from pangeo_fish.bathy import (
    compute_healpix_histogram_region_bin_size,
)

# bathy_url is the path to the bathymetry file
bathy_url = "https://data-taos.ifremer.fr/global_bathy/GEBCO_2024.zarr"

nside = (
    2**refinement_level
)  # parameter equivalent to refinement level used in some function

Importation de la base de donnée de bathymétrie

In [ ]:
full_bathy = xr.open_dataset(
    "https://data-taos.ifremer.fr/demo/database/gebco_2024_new.zarr/",  # "https://data-taos.ifremer.fr/global_bathy/GEBCO_2024.zarr",
    engine="zarr",
    chunks={},
    storage_options=None,
).rename({"lat": "latitude", "lon": "longitude"})
full_bathy

In [ ]:
subset_bathy = full_bathy.sel(
    {dim: slice(bounds[0] - 0.1, bounds[1] + 0.1) for dim, bounds in bbox.items()}
)
ds_histo = compute_healpix_histogram_region_bin_size(
    subset_bathy,
    nside=nside,
    max_depth_m=1000,  # <- profondeur max désirée en mètres
    depth_bin_size=16,  # <- largeur d’un bin en mètres
)

In [ ]:
from pangeo_fish.bathy import batch_compute_pdf_bathy

reshaped_tag = reshape_by_bins(
    tag_log,
    dim="time",
    bins=(
        reference_model.cf.add_bounds(["time"], output_dim="bounds")
        .pipe(bounds_to_bins, bounds_dim="bounds")
        .get("time_bins")
    ),
    other_dim="obs",
).chunk({"time": chunk_time})

pdf_da_func = batch_compute_pdf_bathy(
    ds_histo,
    reshaped_tag,
    target_root,  # remplace target_root
    batch_size=10000,
)
sum_over_cells = pdf_da_func.sum(dim="cells", skipna=True)

bathy_pdf = pdf_da_func / sum_over_cells
bathy_pdf

Enregistre la pdf de bathy seule (si besoin est de la réutiliser indépendamment des autres)

In [ ]:
bathy_pdf.compute().to_zarr(
    f"{target_root}/bathy_pdf_{tag_name}.zarr",
    compute=True,
    mode="w",
    consolidated=True,
    zarr_version=2,
    storage_options=storage_options,
)
# If you want to see the pdf
bathy_pdf.healpix.plot("pdf_bathy", refinement_level, ellipsoid=ellipsoid)

The following cells merge the bathy pdf with other pdfs (you need to calculate at least one other pdf to do so)

In [ ]:
## Open the dataset with the other pdfs
current_total = xr.open_dataset(
    f"{target_root}/total_pdf.zarr",
    engine="zarr",
    chunks={},
    storage_options=storage_options,
)
current_total

In [ ]:
if "pdf_bathy" in current_total.data_vars:
    pass
else:
    current_total = current_total.load()
    current_total.attrs["sources"] = list(
        set(current_total.attrs.get("sources", [])) | {"bathymétrie"}
    )
    merged_pdf = current_total.merge(
        bathy_pdf.drop_indexes(["cell_ids"]), compat="override"
    )

    merged_pdf.to_zarr(
        f"{target_root}/total_pdf.zarr",
        mode="w",
        consolidated=True,
        storage_options=storage_options,
        zarr_format=2,
    )
merged_pdf
import json

print(json.dumps(merged_pdf.attrs))  # ou emission_with_bathy_tide.attrs

In [ ]:
from pangeo_fish.helpers import multi_map_with_synced_sliders, multiplot_healpix

liste = multiplot_healpix(
    [(merged_pdf, ["acoustic", "pdf", "pdf_bathy"])], refinement_level=10
)

multi_map_with_synced_sliders(liste)

## 5.3. Compute a 4th pdf with tide
 Warning, the reference dataset is on a fixed bbox, so the pdf you obtain after merging is smaller and so, less precise (it will be fixed when using Moko dataset)

In [ ]:
from pangeo_fish.tide import *
import xarray as xr
import pandas as pd
from ipywidgets import interact, IntSlider
import numpy as np
import matplotlib.pyplot as plt
from tqdm import tqdm
import sparse

In [ ]:
ds = tag_log["pressure"]
df_resample = ds.resample(
    {"time": "10min"}
).first()  # Take the pressure every ten minutes
df_resample = df_resample.reset_index("time")
df = df_resample.to_dataframe()
df = df.reset_index()  # time is no longer an index
df["time"] = (
    tag_log["time"].resample({"time": "10min"}).first()
)  # <--- Add a column "time"
from scipy.ndimage import median_filter
alpha=5
threshold=1
med = median_filter(df["pressure"].values, size=2*alpha+1, mode="nearest")
df["pressure"] = np.where(np.abs(df["pressure"].values - med) > threshold, med, df["pressure"].values)
tag_test = tide_behav_extr(
    df=df,
    tagno=tag_name,
    tideFL=10,  # time in hour used to detect tide
    tideLV=[
        0.42,
        0.85,
        0.6,
    ],  # hand made parameter ==> see Pedersen work on cod in Atlkantic
    behavFL=16,  # time in hour used to detect tide (use for the detection of behavior)
    behavLV=[0.42, 0.70, 0.2],
    dt=10,
)

tag_test

To see the detection

In [ ]:
plot_tide(tag_test)

In [ ]:
tag_test.to_zarr(
    f"{target_root}/tide_behav.zarr",
    mode="w",
    consolidated=True,
    storage_options=storage_options,
    zarr_format=2,
)
tide_behav = xr.open_dataset(f"{target_root}/tide_behav.zarr", engine="zarr")
tide_behav["behav_found"].plot()

### Import Tide database

In [ ]:
import requests

url = "https://data-taos.ifremer.fr/demo/database/Subset_NS_EC_forTMD30_21_2_2025.nc"

# Télécharger le fichier
print("Téléchargement...")
r = requests.get(url)
with open("Subset_NS_EC_forTMD30_21_2_2025.nc", "wb") as f:
    f.write(r.content)

# Ouvrir avec xarray
print("Ouverture...")
data_360 = xr.open_dataset("Subset_NS_EC_forTMD30_21_2_2025.nc")
data_360

In [ ]:
data = convert_lon_360_to_180(data_360, bbox)

ds_pdf = tide_pdf(tide_behav, data)
ds_pdf["tide_found"].plot()

# Save in zarr
ds_pdf.to_zarr(
    f"{target_root}/tide_pdf.zarr",
    mode="w",
    consolidated=True,
    storage_options=storage_options,
    zarr_format=2,
)

### regrid in healpix

In [ ]:
import xarray as xr
from pangeo_fish.helpers import regrid_dataset_hpresample

LIK_full = xr.open_dataset(f"{target_root}/tide_pdf.zarr", engine="zarr", chunks={})
LIK_full = LIK_full.rename({"mask": "ocean_mask"})
LIK_full["ocean_mask"] = LIK_full["ocean_mask"].compute()

tide_found_saved = LIK_full["tide_found"]

# Coords 2D
lon2d, lat2d = xr.broadcast(LIK_full.longitude, LIK_full.latitude)
lon2d = lon2d.transpose("latitude", "longitude")
lat2d = lat2d.transpose("latitude", "longitude")

# loop to avoid too big datas on the resampler
n_time = LIK_full.sizes["time"]
chunk_size = 2000
all_chunks = []

for chunk_start in range(0, n_time, chunk_size):
    chunk_end = min(chunk_start + chunk_size, n_time)
    print(f"Traitement chunk temporel [{chunk_start}:{chunk_end}] / {n_time}")

    LIK = LIK_full.isel(time=slice(chunk_start, chunk_end))

    # prepare and regrid
    LIK_prepped = LIK.rename({"latitude": "yi", "longitude": "xi"}).assign_coords(
        longitude=(("yi", "xi"), lon2d.values),
        latitude=(("yi", "xi"), lat2d.values),
    )

    reshaped_tide, _ = regrid_dataset_hpresample(
        ds=LIK_prepped, refinement_level=refinement_level, ellipsoid=ellipsoid
    )

    # Densify ocean_mask if sparse
    var = reshaped_tide["ocean_mask"].compute()
    if isinstance(var.data, sparse.SparseArray):
        reshaped_tide["ocean_mask"] = var.copy(data=var.data.todense())

    # Daily resampling
    ds = reshaped_tide.resample(time="1D").mean(skipna=True)
    all_chunks.append(ds)


print("\nConcatenation of chunks...")
ds_full = xr.concat(all_chunks, dim="time")

# Chunking
pdf_chunked = ds_full.pdf.chunk({"time": 10, "cells": -1})
ds_full = ds_full.drop_vars("pdf").assign(pdf=pdf_chunked)
ds_full = ds_full.chunk({"time": 10})
for var in ds_full.variables:
    if "chunks" in ds_full[var].encoding:
        del ds_full[var].encoding["chunks"]

# zarr
store_path = f"{target_root}/tide_pdf_healpix.zarr"
ds_full.to_zarr(store_path, mode="w", compute=False)

n_time = ds_full.sizes["time"]
step = 200
vars_sans_time = ["cell_ids", "latitude", "longitude", "resolution", "ocean_mask"]
for start in range(0, n_time, step):
    end = min(start + step, n_time)
    print(f"Écriture time[{start}:{end}] / {n_time}")
    chunk = ds_full.isel(time=slice(start, end)).drop_vars(vars_sans_time)
    chunk.to_zarr(store_path, mode="r+", region={"time": slice(start, end)})

# Coords et tide_found
coords_only = ds_full[vars_sans_time]
coords_only.to_zarr(store_path, mode="a")

tide_found_resampled = tide_found_saved.resample(time="1D").mean(skipna=True)
tide_found_resampled.sel(time=ds_full.time).to_zarr(store_path, mode="a")

print("DONE")

In [ ]:
ds_full

In [ ]:
ds_full.healpix.plot("pdf", refinement_level=refinement_level, ellipsoid=ellipsoid)

### Merge with other pdfs

In [ ]:
## open the dataset with the others pdfs
current_total = xr.open_dataset(
    f"{target_root}/total_pdf.zarr",
    engine="zarr",
    chunks={},
    storage_options=storage_options,
)

## open the daily tide_pdf
daily = xr.open_dataset(
    f"{target_root}/tide_pdf_healpix.zarr",
    engine="zarr",
    chunks={},
    storage_options=storage_options,
)
daily = daily.groupby("time").mean()
current_total = current_total.load()
current_total

In [ ]:
# Common pixels selection
common_pix = daily.cell_ids.to_index().intersection(current_total.cell_ids.to_index())

# Common time selection
common_time = daily.time.to_index().intersection(current_total.time.to_index())

ds1_common = daily.where(daily.cell_ids.isin(common_pix).compute(), drop=True).sel(
    time=common_time
)

ds1_common = ds1_common.rename({"pdf": "pdf_tide"})

ds2_common = current_total.where(
    current_total.cell_ids.isin(common_pix).compute(), drop=True
).sel(time=common_time)


emission_with_bathy_tide = ds1_common.merge(ds2_common, compat="override", join="exact")
emission_with_bathy_tide.attrs = current_total.attrs.copy()
tide_mask = emission_with_bathy_tide["tide_found"]
emission_with_bathy_tide = emission_with_bathy_tide.drop_vars(
    ["tide_found", "ocean_mask"]
)

In [ ]:
emission_with_bathy_tide = emission_with_bathy_tide.chunk({"time": 3, "cells": -1})
emission_with_bathy_tide.attrs["sources"] = list(
    set(current_total.attrs.get("sources", [])) | {"pdf_tide"}
)

emission_with_bathy_tide.to_zarr(
    f"{target_root}/total_pdf.zarr",
    mode="w",
    consolidated=True,
    storage_options=storage_options,
    zarr_format=2,
)
emission_with_bathy_tide

The following cell present an example of use of multiplot. It allows to see different pdfs of the same fish, if they have the same bbox and the same time span and frequency.

In [ ]:
liste = multiplot_healpix(
    [(emission_with_bathy_tide, ["pdf", "pdf_bathy", "pdf_tide"])],
    refinement_level=refinement_level,
)
liste

multi_map_with_synced_sliders(liste)

## 6. Combine and normalize the X distributions

The normalization ensures that the probabilities sum up to one for each time step. 

In [27]:
from pangeo_fish.helpers import combine_pdfs
from pangeo_fish.helpers import normalize_pdf

In [28]:
current_total = xr.open_dataset(
    f"{target_root}/total_pdf.zarr",
    engine="zarr",
    chunks={},
    storage_options=storage_options,
)
current_total

<xarray.Dataset> Size: 318MB
Dimensions:     (cells: 29677, time: 445)
Coordinates:
    cell_ids    (cells) int64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    latitude    (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    longitude   (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    resolution  float64 8B ...
  * time        (time) datetime64[ns] 4kB 2022-05-20 2022-05-21 ... 2023-08-07
Dimensions without coordinates: cells
Data variables:
    final       (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    initial     (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    mask        (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    pdf         (time, cells) float64 106MB dask.array<chunksize=(3, 29677), meta=np.ndarray>
    pdf_bathy   (time, cells) float64 106MB dask.array<chunksize=(3, 29677), meta=np.ndarray>
    pdf_tide    (time, cells) float64 106MB dask.array<chunksize=(3, 29677), meta=np.ndarray>
Attributes: (12/16)
    acoustic_tag_id:           OPI-612
    comment:                   pangeo-fish == 2026.5.1.dev36+g1b8eac2a8.d2026...
    common_name:               Pollock
    differences_std:           0.75
    grid_type:                 healpix
    history:                   {'Conventions': 'CF-1.4', 'bulletin_date': '20...
    ...                        ...
    project:                   FISHINTEL
    recapture_std:             0.0001
    relative_depth_threshold:  0
    scientific_name:           Pollachius pollachius
    sources:                   ['temperature', 'bathymétrie', 'pdf_tide']
    tag_name:                  A19226

In [29]:
emission_pdf = normalize_pdf(
    ds=current_total,
    chunks=default_chunk_dims,
    dims=dims,
    exclude=("initial", "final", "mask"),
    excluded_pdf=("pdf_tide",),  # ("acoustic",)
)[0]

emission_pdf.to_zarr(
    f"{target_root}/combined.zarr",
    mode="w",
    consolidated=True,
    storage_options=storage_options,
    zarr_format=2,
)
combined = emission_pdf

(
    emission_pdf.sum(dims).hvplot(
        width=500, ylim=(0, 2), title="Sum of the probabilities"
    )
    + emission_pdf.count(dims).hvplot(
        width=500, title="Number of none-zero probabilities"
    )
).opts(shared_axes=False)

/home/cchauveau/pangeo-fish-1106/pangeo-fish/pangeo_fish/helpers.py:1387: UserWarning: you decided to normalize the pdf without: ('pdf_tide',), if you want to include them, change excluded_pdf 
  warnings.warn(


:Layout
   .NdOverlay.I  :NdOverlay   [Variable]
      :Curve   [time]   (value)
   .NdOverlay.II :NdOverlay   [Variable]
      :Curve   [time]   (value)

_The sums should equal to `1`._

In [30]:
combined.healpix.plot("pdf", refinement_level=refinement_level, ellipsoid=ellipsoid)

## 7. Estimate the model's parameters

It is now time to determine the parameters of the model based on the normalized emission matrix.

Precisely, is consists of finding the best `sigma`, which corresponds to the standard deviation of the Brownian motion that models the fish's movement between the time steps.  

To do so, in the following we:
1. Define the lower and upper bounds for `sigma`.  
2. Search for the best `sigma` with `optimize_pdf()`.
3. Save the results of the search (i.e., ` sigma`), along with any additional parameters used during the optimization, a human-readable `.json` file.  

In [31]:
from pangeo_fish.helpers import optimize_pdf

In [32]:
# Open the distributions
emission = xr.open_dataset(
    f"{target_root}/combined.zarr",
    engine="zarr",
    chunks=default_chunk_dims,
    inline_array=True,
    storage_options=storage_options,
)
emission

<xarray.Dataset> Size: 107MB
Dimensions:     (cells: 29677, time: 445)
Coordinates:
    cell_ids    (cells) int64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    latitude    (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    longitude   (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    resolution  float64 8B ...
  * time        (time) datetime64[ns] 4kB 2022-05-20 2022-05-21 ... 2023-08-07
Dimensions without coordinates: cells
Data variables:
    final       (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    initial     (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    mask        (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    pdf         (time, cells) float64 106MB dask.array<chunksize=(1, 29677), meta=np.ndarray>
Attributes: (12/16)
    acoustic_tag_id:           OPI-612
    comment:                   pangeo-fish == 2026.5.1.dev36+g1b8eac2a8.d2026...
    common_name:               Pollock
    differences_std:           0.75
    grid_type:                 healpix
    history:                   {'Conventions': 'CF-1.4', 'bulletin_date': '20...
    ...                        ...
    project:                   FISHINTEL
    recapture_std:             0.0001
    relative_depth_threshold:  0
    scientific_name:           Pollachius pollachius
    sources:                   ['temperature', 'bathymétrie', 'pdf_tide']
    tag_name:                  A19226

In [33]:
# Define the parameter's bounds and search for the best value
params = optimize_pdf(
    ds=emission,
    earth_radius=earth_radius,
    adjustment_factor=adjustment_factor,
    truncate=truncate,
    maximum_speed=maximum_speed,
    tolerance=tolerance,
    dims=dims,
    # the results can be directly saved
    save_parameters=True,
    storage_options=storage_options,
    target_root=f"{target_root}",
    conv_method="LargeHealpixConv",  # there you can chose other conv method (try something and see)
)
params

/home/cchauveau/pangeo-fish-1106/pangeo-fish/pangeo_fish/hmm/prediction.py:282: RuntimeWarning: sigma demandé (1.80e-02 rad) est inférieur ou égal au flou intrinsèque du Down/Up (2.14e-02 rad) pour cette géométrie. Le noyau compact sera quasi ponctuel, le flou effectif sera dominé par le Down/Up et ne pourra pas être réduit davantage.
  warnings.warn(


 
 Func-count     x          f(x)          Procedure
    1       0.018048      4041.34        initial


/home/cchauveau/pangeo-fish-1106/pangeo-fish/pangeo_fish/hmm/prediction.py:282: RuntimeWarning: sigma demandé (2.91e-02 rad) est inférieur ou égal au flou intrinsèque du Down/Up (4.04e-02 rad) pour cette géométrie. Le noyau compact sera quasi ponctuel, le flou effectif sera dominé par le Down/Up et ne pourra pas être réduit davantage.
  warnings.warn(


    2      0.0291404       4158.5        golden
    3      0.0111924      3968.28        golden


/home/cchauveau/pangeo-fish-1106/pangeo-fish/pangeo_fish/hmm/prediction.py:282: RuntimeWarning: sigma demandé (6.96e-03 rad) est inférieur ou égal au flou intrinsèque du Down/Up (1.09e-02 rad) pour cette géométrie. Le noyau compact sera quasi ponctuel, le flou effectif sera dominé par le Down/Up et ne pourra pas être réduit davantage.
  warnings.warn(


...

/home/cchauveau/pangeo-fish-1106/pangeo-fish/pangeo_fish/hmm/prediction.py:282: RuntimeWarning: sigma demandé (6.96e-03 rad) est inférieur ou égal au flou intrinsèque du Down/Up (1.09e-02 rad) pour cette géométrie. Le noyau compact sera quasi ponctuel, le flou effectif sera dominé par le Down/Up et ne pourra pas être réduit davantage.
  warnings.warn(


   21     0.00695647      3968.28        golden


/home/cchauveau/pangeo-fish-1106/pangeo-fish/pangeo_fish/hmm/prediction.py:282: RuntimeWarning: sigma demandé (6.96e-03 rad) est inférieur ou égal au flou intrinsèque du Down/Up (1.09e-02 rad) pour cette géométrie. Le noyau compact sera quasi ponctuel, le flou effectif sera dominé par le Down/Up et ne pourra pas être réduit davantage.
  warnings.warn(


   22      0.0069561      3968.28        golden

Optimization terminated successfully;
The returned value satisfies the termination criteria
(using xtol =  1e-06 )


({'sigma': [0.0069561039139948615],
  'predictors': None,
  'predictor_factory': {'class': "<class 'pangeo_fish.hmm.prediction.UpDownGaussian1DHealpix'>",
   'kwargs': {'grid_info': "HealpixInfo(level=10, ellipsoid=None, indexing_scheme='nested')",
    'sigma': 'None',
    'kernel_sz': 'None',
    'max_compact_kernel_sz': '7',
    'device': 'cpu',
    'dtype': 'torch.float32'}},
  'comment': 'pangeo-fish == 2026.5.1.dev36+g1b8eac2a8.d20261005, healpix-convolution == 0.1.2, xarray == 2025.3.1, xhealpixify == 2025.3.3'},
 <xarray.Dataset> Size: 107MB
 Dimensions:     (cells: 29677, time: 445)
 Coordinates:
   * cell_ids    (cells) int64 237kB 703347 703349 703350 ... 3659780 3659784
     latitude    (cells) float64 237kB 45.93 45.98 45.98 ... 59.01 59.06 59.06
     longitude   (cells) float64 237kB 1.004 1.101 1.005 ... 351.5 351.7 351.5
     resolution  float64 8B 0.0009993
   * time        (time) datetime64[ns] 4kB 2022-05-20 2022-05-21 ... 2023-08-07
 Dimensions without coordinates: c

## 8. State probabilities and Trajectories

In this second to last step, we calculate the spatial probability distribution (based on the `sigma` found earlier) and further compute trajectories.

_NB: the computation precisely relies on `sigma` and the combined emission pdf._

In [34]:
from pangeo_fish.helpers import predict_positions

In [35]:
states, trajectories = predict_positions(
    target_root=f"{target_root}",
    storage_options=storage_options,
    chunks=default_chunk_dims,
    track_modes=track_modes,
    additional_track_quantities=additional_track_quantities,
    save=True,
)

/home/cchauveau/pangeo-fish-1106/pangeo-fish/pangeo_fish/helpers.py:1709: RuntimeWarning: A "predictor_index" entry (filled with 0) is added to the loaded `emission` dataset.
  warnings.warn(
/home/cchauveau/pangeo-fish-1106/pangeo-fish/pangeo_fish/hmm/prediction.py:282: RuntimeWarning: sigma demandé (6.96e-03 rad) est inférieur ou égal au flou intrinsèque du Down/Up (1.09e-02 rad) pour cette géométrie. Le noyau compact sera quasi ponctuel, le flou effectif sera dominé par le Down/Up et ne pourra pas être réduit davantage.
  warnings.warn(
/home/cchauveau/micromamba/envs/pangeo-fish-pr262/lib/python3.11/site-packages/distributed/client.py:3429: UserWarning: Sending large graph of size 101.25 MiB.
This may cause some slowdown.
Consider loading the data with Dask directly
 or using futures or delayed objects to embed the data into the graph without repetition.
See also https://docs.dask.org/en/stable/best-practices.html#load-data-with-dask for more information.
  warnings.warn(
/home/cch

Let's quickly check that the positional probability distribution `states` never sums to 0 for all timesteps!

In [36]:
(
    states.sum(dims).hvplot(width=500, ylim=(0, 2), title="Sum of the probabilities")
    + states.count(dims).hvplot(width=500, title="Number of none-zero probabilities")
).opts(shared_axes=False)

/home/cchauveau/micromamba/envs/pangeo-fish-pr262/lib/python3.11/site-packages/distributed/client.py:3429: UserWarning: Sending large graph of size 100.79 MiB.
This may cause some slowdown.
Consider loading the data with Dask directly
 or using futures or delayed objects to embed the data into the graph without repetition.
See also https://docs.dask.org/en/stable/best-practices.html#load-data-with-dask for more information.
  warnings.warn(
/home/cchauveau/micromamba/envs/pangeo-fish-pr262/lib/python3.11/site-packages/distributed/client.py:3429: UserWarning: Sending large graph of size 100.78 MiB.
This may cause some slowdown.
Consider loading the data with Dask directly
 or using futures or delayed objects to embed the data into the graph without repetition.
See also https://docs.dask.org/en/stable/best-practices.html#load-data-with-dask for more information.
  warnings.warn(


:Layout
   .Curve.I  :Curve   [time]   (states)
   .Curve.II :Curve   [time]   (states)

In [39]:
states

<xarray.Dataset> Size: 106MB
Dimensions:     (cells: 29677, time: 445)
Coordinates:
  * cell_ids    (cells) int64 237kB 703347 703349 703350 ... 3659780 3659784
    latitude    (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    longitude   (cells) float64 237kB dask.array<chunksize=(29677,), meta=np.ndarray>
    resolution  float64 8B 0.0009993
  * time        (time) datetime64[ns] 4kB 2022-05-20 2022-05-21 ... 2023-08-07
Dimensions without coordinates: cells
Data variables:
    states      (time, cells) float64 106MB dask.array<chunksize=(1, 29677), meta=np.ndarray>
Indexes:
    cell_ids  HealpixIndex(level=10, indexing_scheme=nested, kind=pandas)
Attributes: (12/17)
    acoustic_tag_id:           OPI-612
    comment:                   pangeo-fish == 2026.5.1.dev36+g1b8eac2a8.d2026...
    common_name:               Pollock
    differences_std:           0.75
    grid_type:                 healpix
    history:                   {'Conventions': 'CF-1.4', 'bulletin_date': '20...
    ...                        ...
    recapture_std:             0.0001
    relative_depth_threshold:  0
    scientific_name:           Pollachius pollachius
    sources:                   ['temperature', 'bathymétrie', 'pdf_tide']
    tag_name:                  A19226
    sigma:                     [0.0069561039139948615]

In [40]:
states.healpix.plot("states", refinement_level=refinement_level, ellipsoid=ellipsoid)

/home/cchauveau/micromamba/envs/pangeo-fish-pr262/lib/python3.11/site-packages/distributed/client.py:3429: UserWarning: Sending large graph of size 101.25 MiB.
This may cause some slowdown.
Consider loading the data with Dask directly
 or using futures or delayed objects to embed the data into the graph without repetition.
See also https://docs.dask.org/en/stable/best-practices.html#load-data-with-dask for more information.
  warnings.warn(


## 9. Visualization

In this final step, we visualize various aspects of the analysis results to gain insights and interpret the model outcomes. 

We plot the emission distribution, which represents the likelihood of observing a specific temperature difference given the model parameters and configurations. 

Additionally, we visualize the state probabilities, showing the likelihood of the system (i.e, the fish) being in different states (i.e, positions) at each time step. 

We also plot the trajectories decoded before (if you saved them).

They display the possible movement patterns over time. 

Finally, we render the emission matrix and state probabilities in a video and store it.

### 9.1 Plotting the trajectories 

In [37]:
from pangeo_fish.helpers import plot_trajectories

plot_trajectories(
    target_root=f"{target_root}",
    track_modes=track_modes,
    storage_options=storage_options,
    save_html=True,
)

:Layout
   .Overlay.I  :Overlay
      .WMTS.I   :WMTS   [Longitude,Latitude]
      .Path.I   :Path   [Longitude,Latitude]   (speed)
      .Points.I :Points   [Longitude,Latitude]   (speed,triangle_angle)
   .Overlay.II :Overlay
      .WMTS.I   :WMTS   [Longitude,Latitude]
      .Path.I   :Path   [Longitude,Latitude]   (speed)
      .Points.I :Points   [Longitude,Latitude]   (speed,triangle_angle)

### 9.2 Plotting the `states` and `emission` distributions 

In [23]:
from pangeo_fish.helpers import open_distributions, render_distributions

In [24]:
data = open_distributions(
    target_root=target_root,
    storage_options=storage_options,
    chunks=default_chunk_dims,
    chunk_time=chunk_time,
)
data

[KNeighborsResampler] dropping 56 retained cell(s) that passed the wide-neighbourhood 'threshold' test but were never selected by any sample's own Npt-nearest search (would otherwise silently read back as 0.0 for any input).


/home/cchauveau/micromamba/envs/pangeo-fish-pr262/lib/python3.11/site-packages/healpix_resample/bilinear.py:120: UserWarning: Sparse CSR tensor support is in beta state. If you miss a functionality in the sparse tensor support, please submit a feature request to https://github.com/pytorch/pytorch/issues. (Triggered internally at /__w/pytorch/pytorch/aten/src/ATen/SparseCsrTensorImpl.cpp:49.)
  self.M  = M_coo.to_sparse_csr()


<xarray.Dataset> Size: 108MB
Dimensions:    (time: 445, latitude: 193, longitude: 157)
Coordinates:
  * time       (time) datetime64[ns] 4kB 2022-05-20 2022-05-21 ... 2023-08-07
  * latitude   (latitude) float64 2kB 46.0 46.07 46.14 46.2 ... 58.86 58.93 59.0
  * longitude  (longitude) float64 1kB -14.0 -13.9 -13.79 ... 1.795 1.897 2.0
Data variables:
    states     (time, latitude, longitude) float32 54MB dask.array<chunksize=(1, 193, 157), meta=np.ndarray>
    emission   (time, latitude, longitude) float32 54MB dask.array<chunksize=(1, 193, 157), meta=np.ndarray>

The interactive plot above is too large to be stored as a `HMTL` file (as done earlier with the trajectories).

Fortunately, `pangeo-fish` can efficiently render images of `data` and build a video from them! 

In [25]:
%pip install imageio[ffmpeg]

Note: you may need to restart the kernel to use updated packages.


In [26]:
import numpy as np

lon = data["longitude"].values  # (nx,)
lat = data["latitude"].values  # (ny,)
lon_2d, lat_2d = np.meshgrid(lon, lat)  # (ny, nx), même construction qu'avant

data_2d = data.rename({"latitude": "y", "longitude": "x"})
data_2d = data_2d.assign_coords(
    longitude=(("y", "x"), lon_2d),
    latitude=(("y", "x"), lat_2d),
)
data_2d

<xarray.Dataset> Size: 108MB
Dimensions:    (time: 445, y: 193, x: 157)
Coordinates:
  * time       (time) datetime64[ns] 4kB 2022-05-20 2022-05-21 ... 2023-08-07
  * y          (y) float64 2kB 46.0 46.07 46.14 46.2 ... 58.8 58.86 58.93 59.0
  * x          (x) float64 1kB -14.0 -13.9 -13.79 -13.69 ... 1.795 1.897 2.0
    longitude  (y, x) float64 242kB -14.0 -13.9 -13.79 ... 1.795 1.897 2.0
    latitude   (y, x) float64 242kB 46.0 46.0 46.0 46.0 ... 59.0 59.0 59.0 59.0
Data variables:
    states     (time, y, x) float32 54MB dask.array<chunksize=(1, 193, 157), meta=np.ndarray>
    emission   (time, y, x) float32 54MB dask.array<chunksize=(1, 193, 157), meta=np.ndarray>

In [ ]:
video_filename = render_distributions(
    data=data_2d,
    output_path=f"{target_root}/states",
    xlim=bbox["longitude"],
    ylim=bbox["latitude"],
    time_step=time_step,
    extension="mp4",
    frames_dir="images",
    remove_frames=True,
    storage_options=storage_options,
)

## ANNEXE. Impose the model's multiparameter
If you don't have the time or if you want to try other values of sigma\
Use `create_parameter` to set a value of sigma, you can also set different value of sigma in a single tag.\
If you want to test different sigma and compare the result create different folders like in the following cells.
And you can select another convolution method.

In [ ]:
import json
import warnings
from pathlib import Path
import fsspec
from pangeo_fish.helpers import create_parameters, test_parameter
from pangeo_fish.helpers import optimize_pdf

First create the folder


In [ ]:
# Open the distributions
emission = xr.open_dataset(
    f"{target_root}/combined.zarr",
    engine="zarr",
    chunks=default_chunk_dims,
    inline_array=True,
    storage_options=storage_options,
)
# Create a new folder
emission.to_zarr(
    f"{target_root}/hand_sigma/combined.zarr",  # replace "hand_sigma" by another name
    mode="w",
    consolidated=True,
    storage_options=storage_options,
    zarr_format=2,
)

Then add the parameter


In [ ]:
params = create_parameters(
    sigma=[0.002708796991645453],
    sigma_indices=None,
    class_name="UpDownGaussian1DHealpix",  # chose a method you can put something wrong to se them all
    target_root=f"{target_root}/hand_sigma",  # stay consistent here
    save_parameters=True,
)

You can go faster using `test_parameter`. This function do the same as the three cells above. You can put an emission you opened in `emission = None ` or let it at None. If you let it at None it will open the combined pdf which was created in chapter 6.


In [ ]:
params = test_parameter(
    emission=None,
    sigma_tested=[0.001],
    sigma_indices=None,
    Conv_method="UpDownGaussian1DHealpix",
    target_root=target_root,
    saving_root="/hand_sigma_UDG1D",
    default_chunk_dims=default_chunk_dims,
    storage_options=storage_options,
)

In [ ]:
from pangeo_fish.helpers import predict_positions

states_list = [
    predict_positions(
        target_root=f"{target_root}/{subfolder}",
        storage_options=storage_options,
        chunks=default_chunk_dims,
        track_modes=track_modes,
        additional_track_quantities=additional_track_quantities,
        save=True,
    )[0]
    for subfolder in [
        "",
        "hand_sigma",
        "hand_sigma_UDG1D",
    ]
]

If you want to compare the states


In [ ]:
from pangeo_fish.helpers import multi_map_with_synced_sliders, multiplot_healpix

liste = multiplot_healpix(
    [
        (states_list[0], ["states"]),
        (states_list[1], ["states"]),
        (states_list[2], ["states"]),
    ],
    refinement_level=refinement_level,
)
liste

multi_map_with_synced_sliders(liste)

In [ ]:
from pangeo_fish.helpers import plot_trajectories

traj_plots = [
    plot_trajectories(
        target_root=f"{target_root}/{subfolder}",
        track_modes=track_modes,
        storage_options=storage_options,
        save_html=True,
    ).options(title=f"Model's Folder: {subfolder}")
    for subfolder in [
        "",
        "hand_sigma",
        "hand_sigma_UDG1D",
    ]
]
(traj_plots[0] + traj_plots[1] + traj_plots[2]).cols(2)